In [1]:
from cirq_sic import *

In [2]:
d = 3
n = d**2
phi = load_sic_fiducial(d)
sic = d*wh_povm(phi)
P = np.array([[(sic[i]@sic[j]).trace() for j in range(n)] for i in range(n)]).real/d
Phi = (d+1)*np.eye(n) - (d/n)*np.ones((n,n))
R = np.array([[[(sic[i]@sic[j]@sic[k]).trace().real for k in range(n)] for j in range(n)] for i in range(n)])

A_matrices = np.einsum("ijk, kl->lij", R, Phi)
x_center = np.ones(n)/n

In [13]:
import numpy as np
from scipy.linalg import null_space
import plotly.graph_objects as go

def unique_mesh_edges(faces):
    """Return the unique undirected edges of a triangular mesh."""
    edges = set()

    for i, j, k in np.asarray(faces, dtype=int):
        edges.add(tuple(sorted((i, j))))
        edges.add(tuple(sorted((j, k))))
        edges.add(tuple(sorted((k, i))))

    return sorted(edges)

def mesh_edge_coordinates(vertices, edges):
    """Convert mesh edges into Plotly line coordinates."""
    vertices = np.asarray(vertices)

    x = []
    y = []
    z = []

    for i, j in edges:
        x.extend([vertices[i, 0], vertices[j, 0], None])
        y.extend([vertices[i, 1], vertices[j, 1], None])
        z.extend([vertices[i, 2], vertices[j, 2], None])

    return x, y, z

def animate_probability_spectrahedron_section_3D(
    t_values,
    A_matrices,
    x0,
    sweep_direction,
    B,
    section_function,
    subdivisions=3,
    show_mesh_lines=True,
    mesh_opacity=0.65,
    frame_duration=120,
    transition_duration=0,
    width=1000,
    height=850,
):
    """
    Animate the family of 3D sections

        x = x0 + t*sweep_direction + B@y.

    Parameters
    ----------
    t_values:
        One-dimensional array of parameter values.

    A_matrices:
        Matrices defining A(x) = sum_i x_i A_i.

    x0:
        Base probability vector, shape (n,).

    sweep_direction:
        Direction in the probability hyperplane, shape (n,).
        Must satisfy sum(sweep_direction) = 0.

    B:
        Three-dimensional section basis, shape (n, 3).
        Its columns must sum to zero.

    section_function:
        Function computing one 3D section. It should return

            boundary_y, probability_boundary, faces, active

        when called with A_matrices, x_center, B, subdivisions.

    subdivisions:
        Icosphere subdivision level.

    Returns
    -------
    fig:
        Animated Plotly figure.

    section_data:
        List containing the computed data for every parameter value.
    """
    t_values = np.asarray(t_values, dtype=float)
    A_matrices = np.asarray(A_matrices, dtype=float)
    x0 = np.asarray(x0, dtype=float)
    sweep_direction = np.asarray(sweep_direction, dtype=float)
    B = np.asarray(B, dtype=float)

    if t_values.ndim != 1 or len(t_values) == 0:
        raise ValueError("t_values must be a nonempty one-dimensional array.")

    if B.shape != (len(x0), 3):
        raise ValueError("B must have shape (n, 3).")

    if not np.isclose(np.sum(x0), 1.0):
        raise ValueError("x0 must sum to one.")

    if not np.isclose(np.sum(sweep_direction), 0.0):
        raise ValueError("sweep_direction must sum to zero.")

    if not np.allclose(np.sum(B, axis=0), 0.0):
        raise ValueError("Every column of B must sum to zero.")

    section_data = []

    # Compute every section first.
    for t in t_values:
        x_center = x0 + t * sweep_direction

        if np.min(x_center) <= 0:
            raise ValueError(
                f"The center at t={t:g} is not strictly positive."
            )

        M0 = np.einsum("i,ijk->jk", x_center, A_matrices)
        M0 = 0.5 * (M0 + M0.T)

        if np.min(np.linalg.eigvalsh(M0)) <= 0:
            raise ValueError(
                f"A(x_center(t)) is not positive definite at t={t:g}."
            )

        section_results = section_function(
            A_matrices=A_matrices,
            x_center=x_center,
            B=B,
            subdivisions=subdivisions,
        )

        boundary_y, probability_boundary, faces, active = \
            section_results["boundary_y"], section_results["boundary_x"], section_results["faces"], section_results["active"]

        section_data.append({
            "t": t,
            "x_center": x_center,
            "boundary_y": np.asarray(boundary_y),
            "probability_boundary": np.asarray(probability_boundary),
            "faces": np.asarray(faces, dtype=int),
            "active": active,
        })

    # All frames should use the same sphere triangulation.
    reference_faces = section_data[0]["faces"]

    for data in section_data[1:]:
        if not np.array_equal(data["faces"], reference_faces):
            raise ValueError(
                "The triangulation must be identical in every frame."
            )

    faces = reference_faces
    edges = unique_mesh_edges(faces)

    # Determine fixed coordinate ranges over the entire animation.
    all_vertices = np.vstack([
        data["boundary_y"] for data in section_data
    ])

    mins = all_vertices.min(axis=0)
    maxs = all_vertices.max(axis=0)

    center = 0.5 * (mins + maxs)
    half_range = 0.5 * np.max(maxs - mins)

    # Add a little visual padding.
    half_range *= 1.08

    axis_ranges = [
        [center[j] - half_range, center[j] + half_range]
        for j in range(3)
    ]

    def mesh_trace(vertices):
        return go.Mesh3d(
            x=vertices[:, 0],
            y=vertices[:, 1],
            z=vertices[:, 2],
            i=faces[:, 0],
            j=faces[:, 1],
            k=faces[:, 2],
            opacity=mesh_opacity,
            flatshading=True,
            name="section boundary",
            hovertemplate=(
                "y₁=%{x:.5f}<br>"
                "y₂=%{y:.5f}<br>"
                "y₃=%{z:.5f}"
                "<extra></extra>"
            ),
        )

    def edge_trace(vertices):
        edge_x, edge_y, edge_z = mesh_edge_coordinates(vertices, edges)

        return go.Scatter3d(
            x=edge_x,
            y=edge_y,
            z=edge_z,
            mode="lines",
            line=dict(
                color="rgba(0, 0, 0, 0.30)",
                width=1,
            ),
            hoverinfo="skip",
            showlegend=False,
            name="mesh lines",
        )

    first_vertices = section_data[0]["boundary_y"]

    initial_traces = [mesh_trace(first_vertices)]

    if show_mesh_lines:
        initial_traces.append(edge_trace(first_vertices))

    frames = []

    for frame_number, data in enumerate(section_data):
        vertices = data["boundary_y"]

        frame_traces = [mesh_trace(vertices)]

        if show_mesh_lines:
            frame_traces.append(edge_trace(vertices))

        frames.append(
            go.Frame(
                name=str(frame_number),
                data=frame_traces,
                traces=list(range(len(frame_traces))),
                layout=go.Layout(
                    title_text=f"3D section: t = {data['t']:.5g}"
                ),
            )
        )

    slider_steps = []

    for frame_number, data in enumerate(section_data):
        slider_steps.append({
            "method": "animate",
            "label": f"{data['t']:.4g}",
            "args": [
                [str(frame_number)],
                {
                    "mode": "immediate",
                    "frame": {
                        "duration": frame_duration,
                        "redraw": True,
                    },
                    "transition": {
                        "duration": transition_duration,
                    },
                },
            ],
        })

    fig = go.Figure(
        data=initial_traces,
        frames=frames,
    )

    fig.update_layout(
        title=f"3D section: t = {t_values[0]:.5g}",
        width=width,
        height=height,
        margin=dict(l=0, r=0, b=0, t=50),
        scene=dict(
            xaxis=dict(
                title="y₁",
                range=axis_ranges[0],
                autorange=False,
            ),
            yaxis=dict(
                title="y₂",
                range=axis_ranges[1],
                autorange=False,
            ),
            zaxis=dict(
                title="y₃",
                range=axis_ranges[2],
                autorange=False,
            ),
            aspectmode="cube",
            camera=dict(
                eye=dict(x=1.45, y=1.45, z=1.2)
            ),
        ),
        updatemenus=[{
            "type": "buttons",
            "direction": "left",
            "showactive": False,
            "x": 0.0,
            "y": -0.08,
            "buttons": [
                {
                    "label": "Play",
                    "method": "animate",
                    "args": [
                        None,
                        {
                            "fromcurrent": True,
                            "frame": {
                                "duration": frame_duration,
                                "redraw": True,
                            },
                            "transition": {
                                "duration": transition_duration,
                            },
                        },
                    ],
                },
                {
                    "label": "Pause",
                    "method": "animate",
                    "args": [
                        [None],
                        {
                            "mode": "immediate",
                            "frame": {
                                "duration": 0,
                                "redraw": True,
                            },
                            "transition": {
                                "duration": 0,
                            },
                        },
                    ],
                },
            ],
        }],
        sliders=[{
            "active": 0,
            "x": 0.1,
            "y": -0.08,
            "len": 0.85,
            "currentvalue": {
                "prefix": "t = ",
                "visible": True,
            },
            "steps": slider_steps,
        }],
    )

    return fig, section_data

In [ ]:
import numpy as np
from scipy.linalg import null_space

def choose_sweep_direction(B, rng=None):
    """
    Choose a unit vector b4 satisfying

        sum(b4) = 0
        B.T @ b4 = 0.

    B must have shape (n, 3).
    """
    B = np.asarray(B, dtype=float)
    n = B.shape[0]

    if rng is None:
        rng = np.random.default_rng()

    constraints = np.vstack([
        np.ones(n),
        B.T,
    ])

    N = null_space(constraints)

    if N.shape[1] == 0:
        raise ValueError(
            "No fourth direction exists. The ambient probability "
            "hyperplane has insufficient dimension."
        )

    coefficients = rng.normal(size=N.shape[1])
    b4 = N @ coefficients
    b4 /= np.linalg.norm(b4)

    return b4


def make_four_dimensional_probability_basis(n):
    """
    Return B and b4 such that

        B.shape == (n, 3)
        sum(B[:, j]) == 0
        sum(b4) == 0

    and the four columns [B, b4] are orthonormal.
    """
    if n < 5:
        raise ValueError("Need n >= 5 for four independent directions.")

    Q = null_space(np.ones((1, n)))

    directions = Q[:, :4]

    B = directions[:, :3]
    b4 = directions[:, 3]

    return B, b4

def sweep_direction_toward_point(x0, q, B, tol=1e-12):
    x0 = np.asarray(x0, dtype=float)
    q = np.asarray(q, dtype=float)
    B = np.asarray(B, dtype=float)

    v = q - x0

    # Remove the component inside col(B).
    v_perp = v - B @ (np.linalg.pinv(B) @ v)

    norm = np.linalg.norm(v_perp)

    if norm < tol:
        raise ValueError(
            "q - x0 already lies in the current 3D section, "
            "so it does not define a new sweep direction."
        )

    return v_perp / norm

def simplex_t_interval(x0, b4):
    lower = -np.inf
    upper = np.inf

    for xi, vi in zip(x0, b4):
        if vi > 0:
            lower = max(lower, -xi / vi)
        elif vi < 0:
            upper = min(upper, -xi / vi)

    return lower, upper


from scipy.linalg import eigh


def psd_ray_radius(M0, Md, tol=1e-12):
    eigenvalues = eigh(Md, M0, eigvals_only=True)
    smallest = eigenvalues.min()

    if smallest < -tol:
        return -1.0 / smallest

    return np.inf

def marked_point_trace(marked_y, labels):
    return go.Scatter3d(
        x=marked_y[:, 0],
        y=marked_y[:, 1],
        z=marked_y[:, 2],
        mode="markers+text",
        text=labels,
        textposition="top center",
        marker=dict(size=6),
        name="marked probability vectors",
    )

In [ ]:
n = len(A_matrices)

# 1. Start at the uniform probability vector.
x0 = np.ones(n) / n

# 2. Verify that it is strictly PSD-feasible.
M0 = np.tensordot(x0, A_matrices, axes=(0, 0))

if np.linalg.eigvalsh(M0).min() <= 1e-10:
    raise ValueError("The uniform vector is not a strict interior point.")

# 3. Build four orthonormal sum-zero directions.
#B, b4 = make_four_dimensional_probability_basis(n)

sic_indices = [0,1,2]
marked_probabilities = [P[i] for i in sic_indices] + [x_center]
labels = ["p%d" % (i+1) for i in sic_indices] + ["mu"]
B = make_sum_zero_section(marked_probabilities[:-1])
b4 = choose_sweep_direction(B)

# 4. Find the valid sweep interval.
simplex_lower, simplex_upper = simplex_t_interval(x0, b4)

M4 = np.tensordot(b4, A_matrices, axes=(0, 0))

psd_positive = psd_ray_radius(M0, M4)
psd_negative = psd_ray_radius(M0, -M4)

t_lower = max(simplex_lower, -psd_negative)
t_upper = min(simplex_upper, psd_positive)

# 5. Stay slightly inside the allowed interval.
t_values = np.linspace(
    0.95 * t_lower,
    0.95 * t_upper,
    61,
)

fig, section_data = animate_probability_spectrahedron_section_3D(
    t_values=t_values,
    A_matrices=A_matrices,
    x0=x0,
    sweep_direction=b4,
    B=B,
    section_function=probability_spectrahedron_section_3D,
    subdivisions=3,
    frame_duration=100,
    width=1000,
    height=850,
)

fig.show()